In [1]:
from google.colab import drive
drive.mount('/content/drive')

Mounted at /content/drive


# 1. Installing libraries

In [2]:
!pip install -q torch torchvision timm opencv-python pillow numpy matplotlib imageio imageio-ffmpeg

#2. Upload Property Images

In [3]:
from google.colab import files
import os
import cv2
import numpy as np
import torch
import imageio.v2 as imageio
import matplotlib.pyplot as plt

uploaded = files.upload()

IMAGE_PATHS = list(uploaded.keys())

print("Images:")
for p in IMAGE_PATHS:
    print(" -", p)

if len(IMAGE_PATHS) < 1:
    raise ValueError("Please upload at least one image.")

if len(IMAGE_PATHS) > 5:
    IMAGE_PATHS = IMAGE_PATHS[:5]

print(f"\nUsing {len(IMAGE_PATHS)} images")

Saving modern_6.webp to modern_6.webp
Saving modern_5.webp to modern_5.webp
Saving modern_4.webp to modern_4.webp
Saving modern_3.webp to modern_3.webp
Saving modern_2.webp to modern_2.webp
Saving modern_1.webp to modern_1.webp
Images:
 - modern_6.webp
 - modern_5.webp
 - modern_4.webp
 - modern_3.webp
 - modern_2.webp
 - modern_1.webp

Using 5 images


#3. Property Information

In [4]:
PROPERTY = {
    "title": "Modern 3-Bedroom Villa",
    "location": "Kaiserslautern, Germany",
    "price": "€449,000",

    "bedrooms": "3 Bedrooms",
    "bathrooms": "2 Bathrooms",
    "area": "180 m²",

    "description": "Beautiful modern property with spacious living areas and private garden.",

    "phone": "+49 123 1234567",
    "whatsapp": "+49 567 3245678",

    "agent": "Julia Immobilien",

    # Optional
    "logo": "/content/drive/MyDrive/logo.png",

    # Examples:
    # "logo": "/content/logo.png"
}

#4. Video Settings

In [5]:
FPS = 30

TOTAL_DURATION = 30

WIDTH = 1080
HEIGHT = 1920

SCENE_DURATION = TOTAL_DURATION / len(IMAGE_PATHS)

OUTPUT_PATH = "/content/drive/MyDrive/property_reel.mp4"

print("Scene duration:", SCENE_DURATION)
print("Output:", OUTPUT_PATH)

Scene duration: 6.0
Output: /content/drive/MyDrive/property_reel.mp4


#5. Load MiDaS

In [6]:
device = torch.device(
    "cuda" if torch.cuda.is_available() else "cpu"
)

print("Device:", device)

model_type = "DPT_Large"

midas = torch.hub.load(
    "intel-isl/MiDaS",
    model_type
)

midas.to(device)
midas.eval()

midas_transforms = torch.hub.load(
    "intel-isl/MiDaS",
    "transforms"
)

transform = midas_transforms.dpt_transform

print("MiDaS loaded")

Device: cuda
The repository intel-isl_MiDaS does not belong to the list of trusted repositories and as such cannot be downloaded. Do you trust this repository and wish to add it to the trusted list of repositories (y/N)?y
Downloading: "https://github.com/intel-isl/MiDaS/zipball/master" to /root/.cache/torch/hub/master.zip


/usr/local/lib/python3.13/dist-packages/timm/models/layers/__init__.py:49: FutureWarning: Importing from timm.models.layers is deprecated, please import via timm.layers
  warnings.warn(f"Importing from {__name__} is deprecated, please import via timm.layers", FutureWarning)


Downloading: "https://github.com/isl-org/MiDaS/releases/download/v3/dpt_large_384.pt" to /root/.cache/torch/hub/checkpoints/dpt_large_384.pt


100%|██████████| 1.28G/1.28G [00:15<00:00, 86.1MB/s]


MiDaS loaded


Using cache found in /root/.cache/torch/hub/intel-isl_MiDaS_master


#6. Load and prepare images

In [7]:
def load_image(path):
    image = cv2.imread(path)

    if image is None:
        raise ValueError(f"Could not load: {path}")

    image = cv2.cvtColor(
        image,
        cv2.COLOR_BGR2RGB
    )

    return image


images = []

for path in IMAGE_PATHS:

    image = load_image(path)

    images.append(image)

    print(
        os.path.basename(path),
        "→",
        image.shape
    )

modern_6.webp → (397, 595, 3)
modern_5.webp → (540, 840, 3)
modern_4.webp → (200, 336, 3)
modern_3.webp → (573, 860, 3)
modern_2.webp → (482, 722, 3)


#7. Generate depth maps

In [8]:
depth_maps = []

for i, img in enumerate(images):

    print(f"Generating depth {i+1}/{len(images)}...")

    input_batch = transform(img).to(device)

    with torch.no_grad():

        prediction = midas(input_batch)

        prediction = torch.nn.functional.interpolate(
            prediction.unsqueeze(1),
            size=img.shape[:2],
            mode="bicubic",
            align_corners=False
        ).squeeze()

    depth = prediction.cpu().numpy()

    # Normalize
    depth_min = depth.min()
    depth_max = depth.max()

    depth = (
        depth - depth_min
    ) / (
        depth_max - depth_min + 1e-8
    )

    # Smooth
    depth = cv2.GaussianBlur(
        depth,
        (0, 0),
        3
    )

    depth_maps.append(depth)

print("Depth generation complete.")

Generating depth 1/5...
Generating depth 2/5...
Generating depth 3/5...
Generating depth 4/5...
Generating depth 5/5...
Depth generation complete.


#8. Vertical image preparation

##### This is important.

##### A normal property photo might be:

##### 1920 × 1080

##### while Reels need:

##### 1080 × 1920

##### Rather than simply stretching the photo, we'll scale it to cover the vertical frame.

In [9]:
def prepare_vertical(image, depth):

    target_ratio = WIDTH / HEIGHT

    h, w = image.shape[:2]

    current_ratio = w / h

    if current_ratio > target_ratio:

        # Image is too wide
        new_h = HEIGHT
        new_w = int(w * HEIGHT / h)

    else:

        # Image is too tall
        new_w = WIDTH
        new_h = int(h * WIDTH / w)

    image_resized = cv2.resize(
        image,
        (new_w, new_h),
        interpolation=cv2.INTER_LANCZOS4
    )

    depth_resized = cv2.resize(
        depth,
        (new_w, new_h),
        interpolation=cv2.INTER_LINEAR
    )

    x = (new_w - WIDTH) // 2
    y = (new_h - HEIGHT) // 2

    image_crop = image_resized[
        y:y+HEIGHT,
        x:x+WIDTH
    ]

    depth_crop = depth_resized[
        y:y+HEIGHT,
        x:x+WIDTH
    ]

    return image_crop, depth_crop


prepared_images = []
prepared_depths = []

for image, depth in zip(images, depth_maps):

    img, dep = prepare_vertical(
        image,
        depth
    )

    prepared_images.append(img)
    prepared_depths.append(dep)

print("Vertical preparation complete.")

Vertical preparation complete.


#9. Improved parallax engine

#### This is function, but modified for the vertical video and with different movement styles.

In [10]:
def smoothstep(x):
    return x * x * (3 - 2 * x)


def create_parallax_frame(
    image,
    depth,
    progress,
    move_x=0.04,
    move_y=0.015,
    zoom_start=1.0,
    zoom_end=1.08,
    direction=1
):

    image = np.asarray(
        image,
        dtype=np.uint8
    )

    depth = np.asarray(
        depth,
        dtype=np.float32
    )

    h, w = image.shape[:2]

    if depth.shape[:2] != (h, w):

        depth = cv2.resize(
            depth,
            (w, h),
            interpolation=cv2.INTER_LINEAR
        )

    # Normalize depth
    d_min = depth.min()
    d_max = depth.max()

    if d_max > d_min:

        d = (
            depth - d_min
        ) / (
            d_max - d_min
        )

    else:

        d = np.zeros_like(depth)

    # Center depth
    d = d - 0.5

    # Smooth
    d = cv2.GaussianBlur(
        d,
        (0, 0),
        4
    )

    # Smooth cinematic motion
    p = smoothstep(progress)

    # Horizontal camera movement
    x_shift = (
        np.sin(p * np.pi)
        * move_x
        * direction
    )

    # Vertical movement
    y_shift = (
        np.sin(p * np.pi)
        * move_y
    )

    # Zoom
    zoom = (
        zoom_start
        + (zoom_end - zoom_start) * p
    )

    # Coordinates
    xx, yy = np.meshgrid(
        np.arange(w, dtype=np.float32),
        np.arange(h, dtype=np.float32)
    )

    # Depth parallax
    map_x = xx + (
        x_shift * d * w
    )

    map_y = yy + (
        y_shift * d * h
    )

    # Zoom around center
    cx = w / 2
    cy = h / 2

    map_x = (
        cx
        + (map_x - cx) / zoom
    )

    map_y = (
        cy
        + (map_y - cy) / zoom
    )

    map_x = np.asarray(
        map_x,
        dtype=np.float32
    )

    map_y = np.asarray(
        map_y,
        dtype=np.float32
    )

    frame = cv2.remap(
        image,
        map_x,
        map_y,
        interpolation=cv2.INTER_LINEAR,
        borderMode=cv2.BORDER_REFLECT101
    )

    return frame

# 10. Different camera movement for every photograph

##### This makes a big difference.

In [11]:
CAMERA_MOVES = [

    {
        "move_x": 0.035,
        "move_y": 0.010,
        "zoom_start": 1.00,
        "zoom_end": 1.08,
        "direction": 1
    },

    {
        "move_x": 0.050,
        "move_y": 0.012,
        "zoom_start": 1.08,
        "zoom_end": 1.02,
        "direction": -1
    },

    {
        "move_x": 0.040,
        "move_y": 0.018,
        "zoom_start": 1.00,
        "zoom_end": 1.10,
        "direction": 1
    },

    {
        "move_x": 0.055,
        "move_y": 0.010,
        "zoom_start": 1.10,
        "zoom_end": 1.02,
        "direction": -1
    },

    {
        "move_x": 0.035,
        "move_y": 0.015,
        "zoom_start": 1.00,
        "zoom_end": 1.08,
        "direction": 1
    }
]

# 11. Text rendering utilities

##### Now we'll put the property information on top.

In [12]:
from PIL import Image as PILImage
from PIL import ImageDraw
from PIL import ImageFont


FONT_PATH = "/content/drive/MyDrive/fonts/dejavu-sans-font/DejavuSans-MdPB.ttf"
FONT_BOLD_PATH = "/content/drive/MyDrive/fonts/dejavu-sans-font/DejavuSansBold-KEmZ.ttf"


def get_font(size, bold=False):

    path = (
        FONT_BOLD_PATH
        if bold
        else FONT_PATH
    )

    return ImageFont.truetype(
        path,
        size
    )


def add_text(
    frame,
    text,
    xy,
    size=50,
    bold=False,
    opacity=255
):

    pil = PILImage.fromarray(frame)

    overlay = PILImage.new(
        "RGBA",
        pil.size,
        (0, 0, 0, 0)
    )

    draw = ImageDraw.Draw(
        overlay
    )

    font = get_font(
        size,
        bold
    )

    x, y = xy

    # Shadow
    draw.text(
        (x + 3, y + 3),
        text,
        font=font,
        fill=(0, 0, 0, int(opacity * 0.7))
    )

    # Main text
    draw.text(
        (x, y),
        text,
        font=font,
        fill=(255, 255, 255, opacity)
    )

    result = PILImage.alpha_composite(
        pil.convert("RGBA"),
        overlay
    )

    return np.array(
        result.convert("RGB")
    )

def add_logo(frame, logo_path, x=55, y=70, width=220):

    if not logo_path or not os.path.exists(logo_path):
        return frame

    base = PILImage.fromarray(frame).convert("RGBA")

    logo = PILImage.open(logo_path).convert("RGBA")

    # Resize while keeping aspect ratio
    ratio = width / logo.width
    height = int(logo.height * ratio)

    logo = logo.resize(
        (width, height),
        PILImage.Resampling.LANCZOS
    )

    base.alpha_composite(
        logo,
        (x, y)
    )

    return np.array(
        base.convert("RGB")
    )

In [ ]:
# # ============================================================
# # ROBUST FONT SETUP
# # ============================================================

# import os
# import urllib.request
# from PIL import Image as PILImage
# from PIL import ImageDraw, ImageFont


# FONT_PATH = "/content/drive/MyDrive/DejaVuSans.ttf"
# FONT_BOLD_PATH = "/content/drive/MyDrive/DejaVuSans-Bold.ttf"


# # def download_font(url, path):

# #     if not os.path.exists(path):

# #         print("Downloading font...")

# #         urllib.request.urlretrieve(
# #             url,
# #             path
# #         )

# #     # Verify the font actually works
# #     try:

# #         test_font = ImageFont.truetype(
# #             path,
# #             40
# #         )

# #         print(
# #             "Font OK:",
# #             os.path.basename(path)
# #         )

# #     except Exception as e:

# #         print(
# #             "Font error:",
# #             path
# #         )

# #         raise e


# # download_font(
# #     "https://github.com/dejavu-fonts/dejavu/raw/master/ttf/DejaVuSans.ttf",
# #     FONT_PATH
# # )

# # download_font(
# #     "https://github.com/dejavu-fonts/dejavu/raw/master/ttf/DejaVuSans-Bold.ttf",
# #     FONT_BOLD_PATH
# # )


# def get_font(size, bold=False):

#     path = (
#         FONT_BOLD_PATH
#         if bold
#         else FONT_PATH
#     )

#     return ImageFont.truetype(
#         path,
#         size
#     )


# def add_text(
#     frame,
#     text,
#     xy,
#     size=50,
#     bold=False,
#     opacity=255
# ):

#     pil = PILImage.fromarray(
#         frame
#     ).convert("RGBA")

#     overlay = PILImage.new(
#         "RGBA",
#         pil.size,
#         (0, 0, 0, 0)
#     )

#     draw = ImageDraw.Draw(
#         overlay
#     )

#     font = get_font(
#         size,
#         bold
#     )

#     x, y = xy

#     # Shadow
#     draw.text(
#         (x + 4, y + 4),
#         text,
#         font=font,
#         fill=(
#             0,
#             0,
#             0,
#             int(opacity * 0.7)
#         )
#     )

#     # Main text
#     draw.text(
#         (x, y),
#         text,
#         font=font,
#         fill=(
#             255,
#             255,
#             255,
#             opacity
#         )
#     )

#     result = PILImage.alpha_composite(
#         pil,
#         overlay
#     )

#     return np.array(
#         result.convert("RGB")
#     )


# print("Font system ready.")

# 12. Add a dark cinematic gradient

##### This helps white text remain readable over property photos.

In [13]:
def add_gradient(frame):

    h, w = frame.shape[:2]

    gradient = np.zeros(
        (h, w, 3),
        dtype=np.float32
    )

    # Bottom gradient
    for y in range(h):

        strength = max(
            0,
            (y / h - 0.55) / 0.45
        )

        gradient[y, :, :] = (
            strength * 80
        )

    result = (
        frame.astype(np.float32)
        - gradient
    )

    return np.clip(
        result,
        0,
        255
    ).astype(np.uint8)

# 13. Animated text opacity

In [14]:
def fade_opacity(
    progress,
    fade_in=0.12,
    fade_out=0.85
):

    if progress < fade_in:

        return int(
            255 *
            progress /
            fade_in
        )

    if progress > fade_out:

        return int(
            255 *
            (1 - progress) /
            (1 - fade_out)
        )

    return 255

# 14. Create a scene

##### Each photograph becomes a 6-ish second scene.

In [15]:
def create_scene_frame(
    image,
    depth,
    progress,
    scene_index
):

    camera = CAMERA_MOVES[
        scene_index % len(CAMERA_MOVES)
    ]

    frame = create_parallax_frame(
        image,
        depth,
        progress,

        move_x=camera["move_x"],
        move_y=camera["move_y"],

        zoom_start=camera["zoom_start"],
        zoom_end=camera["zoom_end"],

        direction=camera["direction"]
    )

    frame = add_logo(
    frame,
    PROPERTY["logo"],
    x=55, # 55
    y=70, # 70, 40
    width=180
)

    return frame

# 15. Add property overlays

##### We'll vary the information throughout the video.

In [16]:
def add_property_overlay(
    frame,
    global_progress,
    scene_index
):

    frame = add_gradient(frame)

    # ------------------------------------------------
    # TOP BRAND
    # ------------------------------------------------

    frame = add_text(
        frame,
        PROPERTY["agent"],
        (55, 70),
        size=38,
        bold=True
    )

    # ------------------------------------------------
    # FIRST SCENE
    # ------------------------------------------------

    if scene_index == 0:

        opacity = fade_opacity(
            global_progress
        )

        frame = add_text(
            frame,
            PROPERTY["title"],
            (55, 320), # move down to give space for the logo (55, 155) -> (55, 320)
            size=64,
            bold=True,
            opacity=opacity
        )

        frame = add_text(
            frame,
            PROPERTY["location"],
            (55, 400), # move down to give space for the logo (55, 155) -> (55, 400)
            size=38,
            opacity=opacity
        )

    # ------------------------------------------------
    # MIDDLE SCENES
    # ------------------------------------------------

    if scene_index in [1, 2]:

        info = (
            f'{PROPERTY["bedrooms"]}   •   '
            f'{PROPERTY["bathrooms"]}   •   '
            f'{PROPERTY["area"]}'
        )

        frame = add_text(
            frame,
            info,
            (55, HEIGHT - 300),
            size=34,
            bold=True
        )

    # ------------------------------------------------
    # PRICE
    # ------------------------------------------------

    if scene_index == 3:

        frame = add_text(
            frame,
            PROPERTY["price"],
            (55, HEIGHT - 400),
            size=82,
            bold=True
        )

        frame = add_text(
            frame,
            PROPERTY["location"],
            (55, HEIGHT - 310),
            size=38
        )

    # ------------------------------------------------
    # FINAL CTA
    # ------------------------------------------------

    if scene_index == len(IMAGE_PATHS) - 1:

        frame = add_text(
            frame,
            "BOOK A VIEWING",
            (55, HEIGHT - 470),
            size=62,
            bold=True
        )

        frame = add_text(
            frame,
            f'Phone: {PROPERTY["phone"]}',
            (55, HEIGHT - 380),
            size=34
        )

        frame = add_text(
            frame,
            f'WhatsApp: {PROPERTY["whatsapp"]}',
            (55, HEIGHT - 320),
            size=34
        )

    return frame

# 16. Fix camera list typo if necessary (run once)

In [17]:
print(len(CAMERA_MOVES))

5


# 17. Generate the complete 30-second Reel

##### This is the main rendering loop.

In [18]:
print("Rendering video...")

writer = imageio.get_writer(
    OUTPUT_PATH,
    fps=FPS,
    codec="libx264",
    quality=8,
    macro_block_size=None
)

total_frames = int(
    TOTAL_DURATION * FPS
)

num_scenes = len(
    prepared_images
)

scene_frames = int(
    total_frames / num_scenes
)

for scene_index in range(num_scenes):

    print(
        f"Scene {scene_index + 1}/{num_scenes}"
    )

    image = prepared_images[
        scene_index
    ]

    depth = prepared_depths[
        scene_index
    ]

    for frame_index in range(
        scene_frames
    ):

        progress = (
            frame_index /
            max(scene_frames - 1, 1)
        )

        frame = create_scene_frame(
            image,
            depth,
            progress,
            scene_index
        )

        global_frame = (
            scene_index * scene_frames
            + frame_index
        )

        global_progress = (
            global_frame /
            max(total_frames - 1, 1)
        )

        frame = add_property_overlay(
            frame,
            global_progress,
            scene_index
        )

        writer.append_data(frame)


writer.close()

print()
print("DONE")
print("Saved:", OUTPUT_PATH)

Rendering video...
Scene 1/5
Scene 2/5
Scene 3/5
Scene 4/5
Scene 5/5

DONE
Saved: /content/drive/MyDrive/property_reel.mp4


# 18. Preview it

In [19]:
from IPython.display import Video

Video(
    OUTPUT_PATH,
    embed=True
)

# 19. Add music

#### I recommend doing the music with FFmpeg rather than trying to encode it frame-by-frame.

In [ ]:
# from google.colab import files

# uploaded_music = files.upload()

# MUSIC_PATH = "/content/" + list(uploaded_music.keys())[0]

# print("Music:", MUSIC_PATH)

In [23]:
import os
import random

MUSIC_FOLDER = "/content/drive/MyDrive/short-music"

music_files = [
    os.path.join(MUSIC_FOLDER, f)
    for f in os.listdir(MUSIC_FOLDER)
    if f.lower().endswith((".mp3", ".wav", ".m4a"))
]

if not music_files:
    raise ValueError("No music files found in the music folder.")

MUSIC_PATH = random.choice(music_files)

print("Selected music:", os.path.basename(MUSIC_PATH))

Selected music: music_8.mp3


In [24]:
import subprocess

FINAL_OUTPUT = "/content/property_reel_final.mp4"

command = [
    "ffmpeg",
    "-y",

    "-i",
    OUTPUT_PATH,

    "-stream_loop",
    "-1",

    "-i",
    MUSIC_PATH,

    "-filter_complex",
    "[1:a]volume=0.18[a]",

    "-map",
    "0:v",

    "-map",
    "[a]",

    "-c:v",
    "copy",

    "-c:a",
    "aac",

    "-b:a",
    "192k",

    "-shortest",

    FINAL_OUTPUT
]

subprocess.run(
    command,
    check=True
)

print(
    "Final video:",
    FINAL_OUTPUT
)

Final video: /content/property_reel_final.mp4


# 20. Preview final version

In [22]:
Video(
    FINAL_OUTPUT,
    embed=True
)